## Rollout an RGM decoder from a neutral pose

Loads a `distill_prior` checkpoint, initializes the rodent in the model's neutral
`qpos0` pose, and rolls the RGM decoder loop forward for `ROLLOUT_NUM_STEPS`
timesteps at `fixed_logvar = -3`. The resulting qpos trajectory is rendered
using the same helper as above.

In [1]:
import os

os.environ.setdefault("MUJOCO_GL", "egl")
os.environ.setdefault("PYOPENGL_PLATFORM", "egl")

# ============ EDIT THESE ============
DISTILL_PRIOR_CHECKPOINT = "/home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481"
DISTILL_PRIOR_STEP = 54  # None = latest
ROLLOUT_NUM_STEPS = 1000
ROLLOUT_LOGVAR = -4.0
ROLLOUT_SEEDS = [0, 1, 2, 3, 4, 5, 6, 7, 8, 9, 10, 11, 12, 13, 14, 15, 16, 17]  # one rollout per seed

# ============ RENDER SETTINGS ============
ROLLOUT_CAMERA_NAME = "close_profile-rodent"
ROLLOUT_RENDER_HEIGHT = 720
ROLLOUT_RENDER_WIDTH = 1280
ROLLOUT_RENDER_FPS = 50

# Render model: match the rollout env (no-tail-collisions rodent, rescale 0.9).
from scamper.environment.rodent import consts as _rodent_consts

ROLLOUT_WALKER_XML = str(_rodent_consts.RODENT_NO_TAIL_COLLISION_XML)
ROLLOUT_ARENA_XML = str(_rodent_consts.ARENA_XML_PATH)
ROLLOUT_RESCALE_FACTOR = 0.9


In [2]:
import jax
import jax.numpy as jnp
from jax import random
from mujoco import mjx
from omegaconf import OmegaConf

from scamper.environment.rodent import consts as rodent_consts
from scamper.scripts.collect_rollout_dataset_distill import (
    load_distill_prior_checkpoint_for_rollouts,
    create_rgm_policy_fn,
)
from scamper.scripts.collect_rollout_dataset import (
    fix_config_paths,
    create_environment,
)
from scamper.agent.observation_utils import flatten_obs_dict

cfg, policy_params = load_distill_prior_checkpoint_for_rollouts(
    DISTILL_PRIOR_CHECKPOINT, DISTILL_PRIOR_STEP
)

# Override backend to warp and swap in the no-tail-collisions rodent.
OmegaConf.set_struct(cfg.env_config, False)
print(f"  mujoco_impl: {cfg.env_config.mujoco_impl} -> warp")
OmegaConf.update(cfg.env_config, "mujoco_impl", "warp")
new_xml_path = str(rodent_consts.RODENT_NO_TAIL_COLLISION_XML)
print(f"  walker_xml_path: {cfg.env_config.get('walker_xml_path', 'N/A')} -> {new_xml_path}")
OmegaConf.update(cfg.env_config, "walker_xml_path", new_xml_path)
OmegaConf.set_struct(cfg.env_config, True)

cfg = fix_config_paths(cfg)
rollout_env, _reference_clips = create_environment(cfg)
print(f"Loaded distill_prior checkpoint from {DISTILL_PRIOR_CHECKPOINT} step {DISTILL_PRIOR_STEP}")


Loading distill_prior checkpoint from /home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481 at step 54
  mujoco_impl: jax -> warp
  walker_xml_path: /tmp/SCAMPER/scamper/environment/rodent/xmls/rodent.xml -> /home/mila/a/aidan.sirbu/SCAMPER/scamper/environment/rodent/xmls/rodent_no_tail_collisions.xml
Warp 1.11.0 initialized:
   CUDA Toolkit 12.9, Driver 13.0
   Devices:
     "cpu"      : "x86_64"
     "cuda:0"   : "NVIDIA L40S" (45 GiB, sm_89, mempool enabled)
   Kernel cache:
     /home/mila/a/aidan.sirbu/.cache/warp/1.11.0
Warp DeprecationWarning: The symbol `warp.types.warp_type_to_np_dtype` will soon be removed from the public API. It can still be accessed from `warp._src.types.warp_type_to_np_dtype` but might be changed or removed without notice.
Loaded distill_prior checkpoint from /home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481 step 54


In [3]:
import mujoco
import numpy as np

from scamper.environment.utils import dm_scale_spec


def build_rollout_render_model():
    arena = mujoco.MjSpec.from_file(ROLLOUT_ARENA_XML)
    rodent = mujoco.MjSpec.from_file(ROLLOUT_WALKER_XML)
    if ROLLOUT_RESCALE_FACTOR != 1.0:
        rodent = dm_scale_spec(rodent, ROLLOUT_RESCALE_FACTOR)
    frame = arena.worldbody.add_frame(pos=(0, 0, 0), quat=(1, 0, 0, 0))
    body = frame.attach_body(rodent.body("walker"), "", suffix="-rodent")
    body.add_freejoint(name="root")
    model = arena.compile()
    model.vis.global_.offwidth = max(model.vis.global_.offwidth, ROLLOUT_RENDER_WIDTH)
    model.vis.global_.offheight = max(model.vis.global_.offheight, ROLLOUT_RENDER_HEIGHT)
    return model


rollout_render_model = build_rollout_render_model()
rollout_render_data = mujoco.MjData(rollout_render_model)
print(f"render model nq={rollout_render_model.nq}, nv={rollout_render_model.nv}")

_rollout_cam_id = mujoco.mj_name2id(
    rollout_render_model, mujoco.mjtObj.mjOBJ_CAMERA, ROLLOUT_CAMERA_NAME
)
if _rollout_cam_id < 0:
    print(f"warning: camera {ROLLOUT_CAMERA_NAME!r} not found; using default free camera")
    rollout_cam_arg = None
else:
    rollout_cam_arg = _rollout_cam_id


def render_rollout_qpos(qpos_traj):
    renderer = mujoco.Renderer(
        rollout_render_model,
        height=ROLLOUT_RENDER_HEIGHT,
        width=ROLLOUT_RENDER_WIDTH,
    )
    frames = []
    try:
        for t in range(qpos_traj.shape[0]):
            rollout_render_data.qpos[:] = qpos_traj[t]
            mujoco.mj_forward(rollout_render_model, rollout_render_data)
            if rollout_cam_arg is None:
                renderer.update_scene(rollout_render_data)
            else:
                renderer.update_scene(rollout_render_data, camera=rollout_cam_arg)
            frames.append(renderer.render().copy())
    finally:
        renderer.close()
    return frames


render model nq=74, nv=73


In [4]:
def create_neutral_state(env, rng_key):
    """Initialize env state with the model's neutral qpos0 (z=0) and zero qvel."""
    state = env.reset(rng_key)
    mjx_model = env.mjx_model
    neutral_qpos = jnp.array(env.mj_model.qpos0)
    neutral_qpos = neutral_qpos.at[2].set(0)
    data = state.data.replace(qpos=neutral_qpos, qvel=jnp.zeros(mjx_model.nv))
    data = mjx.forward(mjx_model, data)
    return state.replace(data=data)


def run_single_rollout(env, policy_fn, starting_state, num_steps, rng_key):
    jit_step = jax.jit(env.step)

    def step_fn(carry, _):
        state, key = carry
        key, action_key = random.split(key)
        if isinstance(state.obs, dict) or hasattr(state.obs, "get"):
            proprio = flatten_obs_dict(state.obs)["proprioception"]
        else:
            proprio = state.obs
        action, _ = policy_fn(proprio, action_key)
        next_state = jit_step(state, action)
        return (next_state, key), next_state

    (_final_state, _), all_states = jax.lax.scan(
        step_fn, (starting_state, rng_key), None, length=num_steps
    )
    jax.tree_util.tree_map(lambda x: x.block_until_ready(), all_states)
    return all_states


rgm_policy = create_rgm_policy_fn(
    policy_params, cfg, fixed_logvar=ROLLOUT_LOGVAR, deterministic=False
)

rollout_qpos_by_seed = {}
for seed in ROLLOUT_SEEDS:
    rng = random.PRNGKey(seed)
    rng_init, rng_rollout = random.split(rng)
    starting_state = create_neutral_state(rollout_env, rng_init)
    all_states = run_single_rollout(
        rollout_env, rgm_policy, starting_state, ROLLOUT_NUM_STEPS, rng_rollout
    )
    rollout_qpos_by_seed[seed] = np.asarray(all_states.data.qpos)
    print(f"seed={seed}: qpos shape={rollout_qpos_by_seed[seed].shape}")


Module mujoco.mjx.third_party.mujoco_warp._src.smooth e142b0f load on device 'cuda:0' took 17.11 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.collision_driver de6dc98 load on device 'cuda:0' took 4.99 ms  (cached)
Module _nxn_broadphase__locals__kernel_8c837afb 8c837af load on device 'cuda:0' took 4.97 ms  (cached)
Module _primitive_narrowphase__locals__primitive_narrowphase_3a95495c 42367f3 load on device 'cuda:0' took 5.74 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.constraint 51cd7b3 load on device 'cuda:0' took 9.28 ms  (cached)
Module _actuator_velocity__locals__actuator_velocity_0d638ad6 1622c88 load on device 'cuda:0' took 4.94 ms  (cached)
Module _tendon_velocity__locals__tendon_velocity_72b33c1e d7da02d load on device 'cuda:0' took 4.87 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.passive 6808b5e load on device 'cuda:0' took 6.18 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.sensor ca6ca3f load on device 'cuda:0' took

### Save rollouts to an .h5 file

Writes `rollout_qpos_by_seed` to `Plots/rollouts/rollouts_{run_id}_step{step}_logvar{logvar}_steps{num_steps}.h5`
so the rollouts can be reloaded later without regenerating them.


In [5]:
import h5py
from pathlib import Path

ROLLOUT_SAVE_DIR = Path(
    "/home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts"
)
ROLLOUT_SAVE_DIR.mkdir(parents=True, exist_ok=True)

_run_id = Path(DISTILL_PRIOR_CHECKPOINT).name
rollout_save_path = (
    ROLLOUT_SAVE_DIR
    / f"rollouts_{_run_id}_step{DISTILL_PRIOR_STEP}_logvar{ROLLOUT_LOGVAR:g}_steps{ROLLOUT_NUM_STEPS}.h5"
)

with h5py.File(rollout_save_path, "w") as _f:
    _f.attrs["checkpoint"] = DISTILL_PRIOR_CHECKPOINT
    _f.attrs["step"] = DISTILL_PRIOR_STEP
    _f.attrs["logvar"] = float(ROLLOUT_LOGVAR)
    _f.attrs["num_steps"] = int(ROLLOUT_NUM_STEPS)
    _f.attrs["seeds"] = np.asarray(sorted(rollout_qpos_by_seed.keys()))
    for _seed, _qpos in rollout_qpos_by_seed.items():
        _f.create_dataset(
            f"seed_{_seed}", data=np.asarray(_qpos), compression="gzip"
        )

print(f"saved {len(rollout_qpos_by_seed)} rollouts to {rollout_save_path}")


saved 18 rollouts to /home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts/rollouts_260406_130524_381481_step54_logvar-4_steps1000.h5


### Load rollouts from an .h5 file

Repopulates `rollout_qpos_by_seed` from a previously-saved file. Set
`ROLLOUT_LOAD_PATH` to a specific path, or leave it `None` to match the save
cell's naming convention against the current `DISTILL_PRIOR_*` / `ROLLOUT_*`
config.


In [4]:
import h5py
from pathlib import Path

# Optionally override: full path to a rollouts .h5 file. If None, builds the
# path from DISTILL_PRIOR_CHECKPOINT / DISTILL_PRIOR_STEP / ROLLOUT_LOGVAR /
# ROLLOUT_NUM_STEPS (same convention as the save cell).
ROLLOUT_LOAD_PATH = None

_rollouts_dir = Path(
    "/home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts"
)
if ROLLOUT_LOAD_PATH is None:
    _run_id = Path(DISTILL_PRIOR_CHECKPOINT).name
    ROLLOUT_LOAD_PATH = (
        _rollouts_dir
        / f"rollouts_{_run_id}_step{DISTILL_PRIOR_STEP}_logvar{ROLLOUT_LOGVAR:g}_steps{ROLLOUT_NUM_STEPS}.h5"
    )

rollout_qpos_by_seed = {}
with h5py.File(ROLLOUT_LOAD_PATH, "r") as _f:
    print(f"loaded from {ROLLOUT_LOAD_PATH}")
    print(f"  checkpoint: {_f.attrs['checkpoint']}")
    print(f"  step: {_f.attrs['step']}")
    print(f"  logvar: {_f.attrs['logvar']}")
    print(f"  num_steps: {_f.attrs['num_steps']}")
    for _key in _f.keys():
        if _key.startswith("seed_"):
            _seed = int(_key[len("seed_"):])
            rollout_qpos_by_seed[_seed] = _f[_key][:]

print(
    f"populated rollout_qpos_by_seed with {len(rollout_qpos_by_seed)} seeds: "
    f"{sorted(rollout_qpos_by_seed.keys())}"
)


loaded from /home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts/rollouts_260406_130524_381481_step54_logvar-4_steps1000.h5
  checkpoint: /home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481
  step: 54
  logvar: -4.0
  num_steps: 1000
populated rollout_qpos_by_seed with 18 seeds: [0, 1, 2, 3, 4, 5, 6, 7, 8, 9, 10, 11, 12, 13, 14, 15, 16, 17]


In [10]:
import mediapy as media

# Which seeds to display (subset of ROLLOUT_SEEDS). Must be in rollout_qpos_by_seed.
DISPLAY_SEEDS = [6,9]

for seed in DISPLAY_SEEDS:
    if seed not in rollout_qpos_by_seed:
        print(f"seed={seed}: not in rollout_qpos_by_seed; skipping")
        continue
    frames = render_rollout_qpos(rollout_qpos_by_seed[seed])
    print(f"seed={seed} (logvar={ROLLOUT_LOGVAR}, steps={ROLLOUT_NUM_STEPS})")
    media.show_video(frames, fps=ROLLOUT_RENDER_FPS)


seed=6 (logvar=-4.0, steps=1000)


This browser does not support the video tag.


seed=9 (logvar=-4.0, steps=1000)


This browser does not support the video tag.


## 3x3 grid: 9 rodents rendered together

Pick 9 seeds from `rollout_qpos_by_seed` (run the rollout cell above first with
at least those seeds). Each rodent is attached to the arena at its own grid
cell, recolored with a distinct hue, and advanced with its own qpos trajectory.


In [11]:
# ============ EDIT THESE ============
GRID_SEEDS = [0,2,3,4,5,6,8,11,12]  # must all appear in rollout_qpos_by_seed
GRID_SPACING = 0.3  # meters between adjacent grid cells on xy
GRID_CAM_AZIMUTH = -135.00
GRID_CAM_ELEVATION = -21.00
GRID_CAM_DISTANCE = 1.900
GRID_CAM_LOOKAT = (0.040, 0.040, -0.000)
GRID_RENDER_HEIGHT = 720
GRID_RENDER_WIDTH = 1280

# Scene lighting. Each rodent XML ships a per-body trackcom light, so attaching
# 9 rodents stacks 9 lights — we strip them and replace with one directional
# light (parallel rays like sunlight, no falloff, covers the whole grid
# uniformly). diffuse/specular/ambient can exceed 1.0; bump up to brighten.
GRID_LIGHT_DIR = (0.0, 0.0, -1.0)
GRID_LIGHT_AMBIENT = (0.05, 0.05, 0.05)
GRID_LIGHT_DIFFUSE = (0.7, 0.7, 0.7)
GRID_LIGHT_SPECULAR = (0.3, 0.3, 0.3)


-5: 0,1,2,3,5,7,10,11,13
-4: 0,2,3,4,5,6,8,9,11,12,15

In [12]:
import matplotlib.cm as cm
import mediapy as media
import mujoco
import numpy as np

from scamper.environment.utils import dm_scale_spec, _recolour_tree

assert len(GRID_SEEDS) == 9, "GRID_SEEDS must have exactly 9 seeds"
missing = [s for s in GRID_SEEDS if s not in rollout_qpos_by_seed]
assert not missing, (
    f"seeds {missing} not in rollout_qpos_by_seed; run the rollout cell above "
    "with these seeds first"
)

grid_qpos = np.stack([rollout_qpos_by_seed[s] for s in GRID_SEEDS], axis=0)
num_steps_grid = grid_qpos.shape[1]
print(f"grid_qpos shape: {grid_qpos.shape}  (9 rodents, {num_steps_grid} steps, 74 dof)")

# 3x3 grid offsets centered at the origin (row-major over GRID_SEEDS).
grid_xy = np.array(
    [
        (
            (col - 1) * GRID_SPACING,
            (row - 1) * GRID_SPACING,
        )
        for row in range(3)
        for col in range(3)
    ]
)  # (9, 2)

# Distinct color per rodent from the tab10 palette.
colors = [tuple(cm.tab10(i)) for i in range(9)]


def _strip_lights(spec):
    """Delete every light from an MjSpec tree (walker XML ships a per-rodent
    `tracking_light` that would otherwise stack 9x in this scene)."""
    def visit(body):
        for light in list(body.lights):
            spec.delete(light)
        for child in body.bodies:
            visit(child)
    visit(spec.worldbody)


# Build an arena with 9 recolored, rescaled rodents each with its own freejoint.
grid_spec = mujoco.MjSpec.from_file(ROLLOUT_ARENA_XML)

# Replace the 9 stacked trackcom lights with one directional light covering
# the whole grid uniformly (parallel rays, no falloff, unlike a spotlight).
grid_spec.worldbody.add_light(
    name="grid_overhead_light",
    type=int(mujoco.mjtLightType.mjLIGHT_DIRECTIONAL),
    dir=list(GRID_LIGHT_DIR),
    ambient=list(GRID_LIGHT_AMBIENT),
    diffuse=list(GRID_LIGHT_DIFFUSE),
    specular=list(GRID_LIGHT_SPECULAR),
    castshadow=1,
)

for i, color in enumerate(colors):
    rodent_spec = mujoco.MjSpec.from_file(ROLLOUT_WALKER_XML)
    if ROLLOUT_RESCALE_FACTOR != 1.0:
        rodent_spec = dm_scale_spec(rodent_spec, ROLLOUT_RESCALE_FACTOR)
    _strip_lights(rodent_spec)
    for body in rodent_spec.worldbody.bodies:
        _recolour_tree(body, rgba=list(color))
    frame_i = grid_spec.worldbody.add_frame(pos=(0, 0, 0), quat=(1, 0, 0, 0))
    body_i = frame_i.attach_body(rodent_spec.body("walker"), "", suffix=f"-g{i}")
    body_i.add_freejoint(name=f"root-g{i}")

grid_model = grid_spec.compile()
grid_model.vis.global_.offwidth = max(grid_model.vis.global_.offwidth, GRID_RENDER_WIDTH)
grid_model.vis.global_.offheight = max(
    grid_model.vis.global_.offheight, GRID_RENDER_HEIGHT
)
grid_data = mujoco.MjData(grid_model)

nq_single = grid_model.nq // 9
assert nq_single == grid_qpos.shape[2], (
    f"per-rodent nq {nq_single} != qpos dim {grid_qpos.shape[2]}"
)
print(f"compiled grid model: total nq={grid_model.nq}, per-rodent nq={nq_single}")

# Shift each rodent's freejoint xy by its grid cell offset.
qpos_with_offsets = grid_qpos.copy()
qpos_with_offsets[..., 0] += grid_xy[:, 0:1]
qpos_with_offsets[..., 1] += grid_xy[:, 1:2]

grid_cam = mujoco.MjvCamera()
grid_cam.type = mujoco.mjtCamera.mjCAMERA_FREE
grid_cam.azimuth = GRID_CAM_AZIMUTH
grid_cam.elevation = GRID_CAM_ELEVATION
grid_cam.distance = GRID_CAM_DISTANCE
grid_cam.lookat[:] = GRID_CAM_LOOKAT

renderer = mujoco.Renderer(
    grid_model, height=GRID_RENDER_HEIGHT, width=GRID_RENDER_WIDTH
)
grid_frames = []
try:
    for t in range(num_steps_grid):
        for i in range(9):
            start = i * nq_single
            grid_data.qpos[start : start + nq_single] = qpos_with_offsets[i, t]
        mujoco.mj_forward(grid_model, grid_data)
        renderer.update_scene(grid_data, camera=grid_cam)
        grid_frames.append(renderer.render().copy())
finally:
    renderer.close()

media.show_video(grid_frames, fps=ROLLOUT_RENDER_FPS)


grid_qpos shape: (9, 1000, 74)  (9 rodents, 1000 steps, 74 dof)
compiled grid model: total nq=666, per-rodent nq=74


This browser does not support the video tag.


## Interactive camera picker — first frame of the grid scene

Renders the pose at `t=0` for the currently-built `grid_model` and exposes
sliders for azimuth / elevation / distance / lookat. Click **Capture Camera**
to print a snippet you can paste back into the config cell (`GRID_CAM_*`),
then re-run the grid build cell to regenerate the video at the new angle.

Requires the grid build cell above to have run (needs `grid_model`,
`grid_data`, `qpos_with_offsets`, `nq_single`).


In [35]:
import io

import ipywidgets as widgets
import mujoco
import numpy as np
import PIL.Image
from IPython.display import display as ipy_display

# Interactive-preview resolution (keep modest for responsive sliders).
PREVIEW_HEIGHT = 720
PREVIEW_WIDTH = 1280

# Pose the grid scene on the first frame.
for _i in range(9):
    _start = _i * nq_single
    grid_data.qpos[_start : _start + nq_single] = qpos_with_offsets[_i, 0]
mujoco.mj_forward(grid_model, grid_data)

preview_renderer = mujoco.Renderer(
    grid_model, height=PREVIEW_HEIGHT, width=PREVIEW_WIDTH
)
free_cam = mujoco.MjvCamera()
free_cam.type = mujoco.mjtCamera.mjCAMERA_FREE

# Seed from a previous capture if it exists, else from the GRID_CAM_* config.
try:
    _has_capture = bool(captured_grid_cam)
except NameError:
    captured_grid_cam = {}
    _has_capture = False

if _has_capture:
    free_cam.azimuth = captured_grid_cam["azimuth"]
    free_cam.elevation = captured_grid_cam["elevation"]
    free_cam.distance = captured_grid_cam["distance"]
    free_cam.lookat[:] = captured_grid_cam["lookat"]
else:
    free_cam.azimuth = GRID_CAM_AZIMUTH
    free_cam.elevation = GRID_CAM_ELEVATION
    free_cam.distance = GRID_CAM_DISTANCE
    free_cam.lookat[:] = GRID_CAM_LOOKAT

img_widget = widgets.Image(
    format="jpeg", layout=widgets.Layout(width=f"{PREVIEW_WIDTH}px")
)


def render_view(change=None):
    preview_renderer.update_scene(grid_data, camera=free_cam)
    frame = preview_renderer.render()
    buf = io.BytesIO()
    PIL.Image.fromarray(frame).save(buf, format="JPEG", quality=90)
    img_widget.value = buf.getvalue()


azimuth_slider = widgets.FloatSlider(
    value=float(free_cam.azimuth), min=-180, max=180, step=1,
    description="Azimuth", continuous_update=True,
    layout=widgets.Layout(width="500px"),
)
elevation_slider = widgets.FloatSlider(
    value=float(free_cam.elevation), min=-90, max=90, step=1,
    description="Elevation", continuous_update=True,
    layout=widgets.Layout(width="500px"),
)
distance_slider = widgets.FloatSlider(
    value=float(free_cam.distance), min=0.1, max=8.0, step=0.05,
    description="Distance", continuous_update=True,
    layout=widgets.Layout(width="500px"),
)
lookat_x = widgets.FloatSlider(
    value=float(free_cam.lookat[0]), min=-3, max=3, step=0.01,
    description="Lookat X", continuous_update=True,
    layout=widgets.Layout(width="500px"),
)
lookat_y = widgets.FloatSlider(
    value=float(free_cam.lookat[1]), min=-3, max=3, step=0.01,
    description="Lookat Y", continuous_update=True,
    layout=widgets.Layout(width="500px"),
)
lookat_z = widgets.FloatSlider(
    value=float(free_cam.lookat[2]), min=-1, max=2, step=0.01,
    description="Lookat Z", continuous_update=True,
    layout=widgets.Layout(width="500px"),
)


def on_slider_change(change):
    free_cam.azimuth = azimuth_slider.value
    free_cam.elevation = elevation_slider.value
    free_cam.distance = distance_slider.value
    free_cam.lookat[:] = [lookat_x.value, lookat_y.value, lookat_z.value]
    render_view()


for _sl in [
    azimuth_slider, elevation_slider, distance_slider,
    lookat_x, lookat_y, lookat_z,
]:
    _sl.observe(on_slider_change, names="value")

capture_output = widgets.Output()
capture_btn = widgets.Button(description="Capture Camera", button_style="success")


def on_capture(btn):
    captured_grid_cam["azimuth"] = azimuth_slider.value
    captured_grid_cam["elevation"] = elevation_slider.value
    captured_grid_cam["distance"] = distance_slider.value
    captured_grid_cam["lookat"] = [lookat_x.value, lookat_y.value, lookat_z.value]
    snippet = (
        f"GRID_CAM_AZIMUTH = {captured_grid_cam['azimuth']:.2f}\n"
        f"GRID_CAM_ELEVATION = {captured_grid_cam['elevation']:.2f}\n"
        f"GRID_CAM_DISTANCE = {captured_grid_cam['distance']:.3f}\n"
        f"GRID_CAM_LOOKAT = ("
        f"{captured_grid_cam['lookat'][0]:.3f}, "
        f"{captured_grid_cam['lookat'][1]:.3f}, "
        f"{captured_grid_cam['lookat'][2]:.3f})"
    )
    with capture_output:
        capture_output.clear_output()
        print("# paste into the config cell:")
        print(snippet)


capture_btn.on_click(on_capture)
render_view()

controls = widgets.VBox(
    [
        widgets.HBox([azimuth_slider, elevation_slider]),
        widgets.HBox([distance_slider]),
        widgets.HBox([lookat_x, lookat_y, lookat_z]),
        widgets.HBox([capture_btn]),
        capture_output,
    ]
)
ipy_display(widgets.VBox([img_widget, controls]))


# Rollout + render with the motion prior (self-contained)

Uses the `prior` subnet of a `distill_prior` checkpoint (the MLP that predicts
intention distributions from proprioception alone) instead of the RGM. All
state lives in `PRIOR_*` / `prior_*` variables so nothing interacts with the
RGM section above — this section can be run on its own.


### Config


In [3]:
# ============ EDIT THESE ============
PRIOR_CHECKPOINT = "/home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481"
PRIOR_STEP = 54  # None = latest
PRIOR_LOGVAR = -4.0  # None = use predicted logvar
PRIOR_DETERMINISTIC = False
PRIOR_NUM_STEPS = 1000
PRIOR_SEEDS = [0, 1, 2, 3, 4, 5, 6, 7, 8, 9, 10, 11, 12, 13, 14, 15, 16, 17]

# Single-rodent render settings
PRIOR_RENDER_CAMERA_NAME = "close_profile-rodent"
PRIOR_RENDER_HEIGHT = 720
PRIOR_RENDER_WIDTH = 1280
PRIOR_RENDER_FPS = 50

# Which subset of seeds to display as individual videos
PRIOR_DISPLAY_SEEDS = [0, 3, 7]

# 3x3 grid settings
PRIOR_GRID_SEEDS = [0, 1, 2, 3, 4, 5, 6, 7, 8]  # must have exactly 9
PRIOR_GRID_SPACING = 0.3
PRIOR_GRID_CAM_AZIMUTH = -135.00
PRIOR_GRID_CAM_ELEVATION = -21.00
PRIOR_GRID_CAM_DISTANCE = 1.900
PRIOR_GRID_CAM_LOOKAT = (0.040, 0.040, -0.000)
PRIOR_GRID_RENDER_HEIGHT = 720
PRIOR_GRID_RENDER_WIDTH = 1280

# Grid scene lighting (directional; no falloff, uniform over the grid)
PRIOR_GRID_LIGHT_DIR = (0.0, 0.0, -1.0)
PRIOR_GRID_LIGHT_AMBIENT = (0.05, 0.05, 0.05)
PRIOR_GRID_LIGHT_DIFFUSE = (0.7, 0.7, 0.7)
PRIOR_GRID_LIGHT_SPECULAR = (0.3, 0.3, 0.3)

# Walker / arena (match the rollout env's no-tail-collisions rodent, rescale 0.9)
from scamper.environment.rodent import consts as _prior_rodent_consts
PRIOR_WALKER_XML = str(_prior_rodent_consts.RODENT_NO_TAIL_COLLISION_XML)
PRIOR_ARENA_XML = str(_prior_rodent_consts.ARENA_XML_PATH)
PRIOR_RESCALE_FACTOR = 0.9


### Load checkpoint and build env


In [4]:
import os

os.environ.setdefault("MUJOCO_GL", "egl")
os.environ.setdefault("PYOPENGL_PLATFORM", "egl")

from omegaconf import OmegaConf

from scamper.scripts.collect_rollout_dataset import (
    fix_config_paths,
    create_environment,
    create_prior_policy_fn,
)
from scamper.scripts.collect_rollout_dataset_distill import (
    load_distill_prior_checkpoint_for_rollouts,
)

prior_cfg, prior_policy_params = load_distill_prior_checkpoint_for_rollouts(
    PRIOR_CHECKPOINT, PRIOR_STEP
)

# Match the rollout env the checkpoint was trained in: warp backend, no-tail
# collisions rodent.
OmegaConf.set_struct(prior_cfg.env_config, False)
OmegaConf.update(prior_cfg.env_config, "mujoco_impl", "warp")
OmegaConf.update(prior_cfg.env_config, "walker_xml_path", PRIOR_WALKER_XML)
OmegaConf.set_struct(prior_cfg.env_config, True)

prior_cfg = fix_config_paths(prior_cfg)
prior_env, _prior_reference_clips = create_environment(prior_cfg)
print(f"Loaded prior checkpoint from {PRIOR_CHECKPOINT} step {PRIOR_STEP}")


Loading distill_prior checkpoint from /home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481 at step 54


Warp 1.11.0 initialized:
   CUDA Toolkit 12.9, Driver 13.0
   Devices:
     "cpu"      : "x86_64"
     "cuda:0"   : "NVIDIA L40S" (45 GiB, sm_89, mempool enabled)
   Kernel cache:
     /home/mila/a/aidan.sirbu/.cache/warp/1.11.0
Warp DeprecationWarning: The symbol `warp.types.warp_type_to_np_dtype` will soon be removed from the public API. It can still be accessed from `warp._src.types.warp_type_to_np_dtype` but might be changed or removed without notice.
Loaded prior checkpoint from /home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481 step 54


### Rollout with the motion prior

Builds the prior policy (`create_prior_policy_fn` on the `prior` subnet of the
checkpoint) and rolls it out from the model's neutral pose for each seed in
`PRIOR_SEEDS`. Populates `prior_rollout_qpos_by_seed`.


In [3]:
import jax
import jax.numpy as jnp
import numpy as np
from jax import random
from mujoco import mjx

from scamper.agent.observation_utils import flatten_obs_dict


def _prior_create_neutral_state(env, rng_key):
    state = env.reset(rng_key)
    mjx_model = env.mjx_model
    neutral_qpos = jnp.array(env.mj_model.qpos0)
    neutral_qpos = neutral_qpos.at[2].set(0)
    data = state.data.replace(qpos=neutral_qpos, qvel=jnp.zeros(mjx_model.nv))
    data = mjx.forward(mjx_model, data)
    return state.replace(data=data)


def _prior_run_single_rollout(env, policy_fn, starting_state, num_steps, rng_key):
    jit_step = jax.jit(env.step)

    def step_fn(carry, _):
        state, key = carry
        key, action_key = random.split(key)
        if isinstance(state.obs, dict) or hasattr(state.obs, "get"):
            proprio = flatten_obs_dict(state.obs)["proprioception"]
        else:
            proprio = state.obs
        action, _ = policy_fn(proprio, action_key)
        next_state = jit_step(state, action)
        return (next_state, key), next_state

    (_final_state, _), all_states = jax.lax.scan(
        step_fn, (starting_state, rng_key), None, length=num_steps
    )
    jax.tree_util.tree_map(lambda x: x.block_until_ready(), all_states)
    return all_states


prior_policy_fn = create_prior_policy_fn(
    prior_policy_params,
    prior_cfg,
    fixed_logvar=PRIOR_LOGVAR,
    deterministic=PRIOR_DETERMINISTIC,
)

prior_rollout_qpos_by_seed = {}
for seed in PRIOR_SEEDS:
    rng = random.PRNGKey(seed)
    rng_init, rng_rollout = random.split(rng)
    starting_state = _prior_create_neutral_state(prior_env, rng_init)
    all_states = _prior_run_single_rollout(
        prior_env, prior_policy_fn, starting_state, PRIOR_NUM_STEPS, rng_rollout
    )
    prior_rollout_qpos_by_seed[seed] = np.asarray(all_states.data.qpos)
    print(f"seed={seed}: qpos shape={prior_rollout_qpos_by_seed[seed].shape}")


Module mujoco.mjx.third_party.mujoco_warp._src.smooth e142b0f load on device 'cuda:0' took 17.10 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.collision_driver de6dc98 load on device 'cuda:0' took 5.11 ms  (cached)
Module _nxn_broadphase__locals__kernel_8c837afb 8c837af load on device 'cuda:0' took 5.25 ms  (cached)
Module _primitive_narrowphase__locals__primitive_narrowphase_3a95495c 42367f3 load on device 'cuda:0' took 5.98 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.constraint 51cd7b3 load on device 'cuda:0' took 9.28 ms  (cached)
Module _actuator_velocity__locals__actuator_velocity_0d638ad6 1622c88 load on device 'cuda:0' took 5.01 ms  (cached)
Module _tendon_velocity__locals__tendon_velocity_72b33c1e d7da02d load on device 'cuda:0' took 5.63 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.passive 6808b5e load on device 'cuda:0' took 6.53 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.sensor ca6ca3f load on device 'cuda:0' took

### Save prior rollouts to an .h5 file

Writes `prior_rollout_qpos_by_seed` to `Plots/rollouts/prior_rollouts_{run_id}_step{step}_logvar{logvar}_steps{num_steps}.h5`.


In [4]:
import h5py
from pathlib import Path
import numpy as np

PRIOR_ROLLOUT_SAVE_DIR = Path(
    "/home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts"
)
PRIOR_ROLLOUT_SAVE_DIR.mkdir(parents=True, exist_ok=True)

_run_id = Path(PRIOR_CHECKPOINT).name
_logvar_tag = "predicted" if PRIOR_LOGVAR is None else f"{PRIOR_LOGVAR:g}"
prior_rollout_save_path = (
    PRIOR_ROLLOUT_SAVE_DIR
    / f"prior_rollouts_{_run_id}_step{PRIOR_STEP}_logvar{_logvar_tag}_steps{PRIOR_NUM_STEPS}.h5"
)

with h5py.File(prior_rollout_save_path, "w") as _f:
    _f.attrs["checkpoint"] = PRIOR_CHECKPOINT
    _f.attrs["step"] = PRIOR_STEP
    _f.attrs["logvar"] = "predicted" if PRIOR_LOGVAR is None else float(PRIOR_LOGVAR)
    _f.attrs["num_steps"] = int(PRIOR_NUM_STEPS)
    _f.attrs["deterministic"] = bool(PRIOR_DETERMINISTIC)
    _f.attrs["seeds"] = np.asarray(sorted(prior_rollout_qpos_by_seed.keys()))
    for _seed, _qpos in prior_rollout_qpos_by_seed.items():
        _f.create_dataset(
            f"seed_{_seed}", data=np.asarray(_qpos), compression="gzip"
        )

print(f"saved {len(prior_rollout_qpos_by_seed)} rollouts to {prior_rollout_save_path}")


saved 18 rollouts to /home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts/prior_rollouts_260406_130524_381481_step54_logvar-4_steps1000.h5


### Load prior rollouts from an .h5 file


In [5]:
import h5py
from pathlib import Path

# Optionally override: full path to a prior rollouts .h5 file. If None, rebuilds
# the path using the same naming convention as the save cell.
PRIOR_ROLLOUT_LOAD_PATH = None

_prior_rollouts_dir = Path(
    "/home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts"
)
if PRIOR_ROLLOUT_LOAD_PATH is None:
    _run_id = Path(PRIOR_CHECKPOINT).name
    _logvar_tag = "predicted" if PRIOR_LOGVAR is None else f"{PRIOR_LOGVAR:g}"
    PRIOR_ROLLOUT_LOAD_PATH = (
        _prior_rollouts_dir
        / f"prior_rollouts_{_run_id}_step{PRIOR_STEP}_logvar{_logvar_tag}_steps{PRIOR_NUM_STEPS}.h5"
    )

prior_rollout_qpos_by_seed = {}
with h5py.File(PRIOR_ROLLOUT_LOAD_PATH, "r") as _f:
    print(f"loaded from {PRIOR_ROLLOUT_LOAD_PATH}")
    print(f"  checkpoint: {_f.attrs['checkpoint']}")
    print(f"  step: {_f.attrs['step']}")
    print(f"  logvar: {_f.attrs['logvar']}")
    print(f"  num_steps: {_f.attrs['num_steps']}")
    for _key in _f.keys():
        if _key.startswith("seed_"):
            _seed = int(_key[len("seed_"):])
            prior_rollout_qpos_by_seed[_seed] = _f[_key][:]

print(
    f"populated prior_rollout_qpos_by_seed with {len(prior_rollout_qpos_by_seed)} seeds: "
    f"{sorted(prior_rollout_qpos_by_seed.keys())}"
)


loaded from /home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/rollouts/prior_rollouts_260406_130524_381481_step54_logvar-4_steps1000.h5
  checkpoint: /home/mila/a/aidan.sirbu/SCAMPER/scratch/distill_prior_checkpoints/260406_130524_381481
  step: 54
  logvar: -4.0
  num_steps: 1000
populated prior_rollout_qpos_by_seed with 18 seeds: [0, 1, 2, 3, 4, 5, 6, 7, 8, 9, 10, 11, 12, 13, 14, 15, 16, 17]


### Display individual prior rollouts

Renders one video per seed in `PRIOR_DISPLAY_SEEDS`. Builds a dedicated
single-rodent render model tuned to `PRIOR_RENDER_*` settings.


In [ ]:
import mediapy as media
import mujoco
import numpy as np

from scamper.environment.utils import dm_scale_spec


def _build_prior_render_model():
    arena = mujoco.MjSpec.from_file(PRIOR_ARENA_XML)
    rodent = mujoco.MjSpec.from_file(PRIOR_WALKER_XML)
    if PRIOR_RESCALE_FACTOR != 1.0:
        rodent = dm_scale_spec(rodent, PRIOR_RESCALE_FACTOR)
    frame = arena.worldbody.add_frame(pos=(0, 0, 0), quat=(1, 0, 0, 0))
    body = frame.attach_body(rodent.body("walker"), "", suffix="-rodent")
    body.add_freejoint(name="root")
    model = arena.compile()
    model.vis.global_.offwidth = max(model.vis.global_.offwidth, PRIOR_RENDER_WIDTH)
    model.vis.global_.offheight = max(model.vis.global_.offheight, PRIOR_RENDER_HEIGHT)
    return model


prior_render_model = _build_prior_render_model()
prior_render_data = mujoco.MjData(prior_render_model)

_prior_cam_id = mujoco.mj_name2id(
    prior_render_model, mujoco.mjtObj.mjOBJ_CAMERA, PRIOR_RENDER_CAMERA_NAME
)
prior_cam_arg = _prior_cam_id if _prior_cam_id >= 0 else None
if prior_cam_arg is None:
    print(f"warning: camera {PRIOR_RENDER_CAMERA_NAME!r} not found; using default free camera")


def render_prior_qpos(qpos_traj):
    renderer = mujoco.Renderer(
        prior_render_model, height=PRIOR_RENDER_HEIGHT, width=PRIOR_RENDER_WIDTH
    )
    frames = []
    try:
        for t in range(qpos_traj.shape[0]):
            prior_render_data.qpos[:] = qpos_traj[t]
            mujoco.mj_forward(prior_render_model, prior_render_data)
            if prior_cam_arg is None:
                renderer.update_scene(prior_render_data)
            else:
                renderer.update_scene(prior_render_data, camera=prior_cam_arg)
            frames.append(renderer.render().copy())
    finally:
        renderer.close()
    return frames


for seed in PRIOR_DISPLAY_SEEDS:
    if seed not in prior_rollout_qpos_by_seed:
        print(f"seed={seed}: not in prior_rollout_qpos_by_seed; skipping")
        continue
    frames = render_prior_qpos(prior_rollout_qpos_by_seed[seed])
    print(f"[prior] seed={seed} (logvar={PRIOR_LOGVAR}, steps={PRIOR_NUM_STEPS})")
    media.show_video(frames, fps=PRIOR_RENDER_FPS)


### 3x3 grid of 9 prior rodents

Attaches 9 recolored rodents to the arena in a 3x3 grid, strips per-rodent
tracking lights, and adds one directional overhead light. Uses `PRIOR_GRID_*`
config knobs.


In [6]:
import os

os.environ.setdefault("MUJOCO_GL", "egl")
os.environ.setdefault("PYOPENGL_PLATFORM", "egl")

import matplotlib.cm as cm
import mediapy as media
import mujoco
import numpy as np

from scamper.environment.utils import dm_scale_spec, _recolour_tree

assert len(PRIOR_GRID_SEEDS) == 9, "PRIOR_GRID_SEEDS must have exactly 9 seeds"
_prior_missing = [s for s in PRIOR_GRID_SEEDS if s not in prior_rollout_qpos_by_seed]
assert not _prior_missing, (
    f"seeds {_prior_missing} not in prior_rollout_qpos_by_seed; run the rollout "
    "cell (or the load cell) above first"
)

_prior_grid_qpos = np.stack(
    [prior_rollout_qpos_by_seed[s] for s in PRIOR_GRID_SEEDS], axis=0
)
_prior_num_steps_grid = _prior_grid_qpos.shape[1]

_prior_grid_xy = np.array(
    [
        ((col - 1) * PRIOR_GRID_SPACING, (row - 1) * PRIOR_GRID_SPACING)
        for row in range(3)
        for col in range(3)
    ]
)

_prior_colors = [tuple(cm.tab10(i)) for i in range(9)]


def _prior_strip_lights(spec):
    def visit(body):
        for light in list(body.lights):
            spec.delete(light)
        for child in body.bodies:
            visit(child)
    visit(spec.worldbody)


prior_grid_spec = mujoco.MjSpec.from_file(PRIOR_ARENA_XML)
prior_grid_spec.worldbody.add_light(
    name="prior_grid_overhead_light",
    type=int(mujoco.mjtLightType.mjLIGHT_DIRECTIONAL),
    dir=list(PRIOR_GRID_LIGHT_DIR),
    ambient=list(PRIOR_GRID_LIGHT_AMBIENT),
    diffuse=list(PRIOR_GRID_LIGHT_DIFFUSE),
    specular=list(PRIOR_GRID_LIGHT_SPECULAR),
    castshadow=1,
)

for i, color in enumerate(_prior_colors):
    rodent_spec = mujoco.MjSpec.from_file(PRIOR_WALKER_XML)
    if PRIOR_RESCALE_FACTOR != 1.0:
        rodent_spec = dm_scale_spec(rodent_spec, PRIOR_RESCALE_FACTOR)
    _prior_strip_lights(rodent_spec)
    for body in rodent_spec.worldbody.bodies:
        _recolour_tree(body, rgba=list(color))
    frame_i = prior_grid_spec.worldbody.add_frame(pos=(0, 0, 0), quat=(1, 0, 0, 0))
    body_i = frame_i.attach_body(rodent_spec.body("walker"), "", suffix=f"-pg{i}")
    body_i.add_freejoint(name=f"root-pg{i}")

prior_grid_model = prior_grid_spec.compile()
prior_grid_model.vis.global_.offwidth = max(
    prior_grid_model.vis.global_.offwidth, PRIOR_GRID_RENDER_WIDTH
)
prior_grid_model.vis.global_.offheight = max(
    prior_grid_model.vis.global_.offheight, PRIOR_GRID_RENDER_HEIGHT
)
prior_grid_data = mujoco.MjData(prior_grid_model)

prior_nq_single = prior_grid_model.nq // 9
assert prior_nq_single == _prior_grid_qpos.shape[2]

prior_qpos_with_offsets = _prior_grid_qpos.copy()
prior_qpos_with_offsets[..., 0] += _prior_grid_xy[:, 0:1]
prior_qpos_with_offsets[..., 1] += _prior_grid_xy[:, 1:2]

prior_grid_cam = mujoco.MjvCamera()
prior_grid_cam.type = mujoco.mjtCamera.mjCAMERA_FREE
prior_grid_cam.azimuth = PRIOR_GRID_CAM_AZIMUTH
prior_grid_cam.elevation = PRIOR_GRID_CAM_ELEVATION
prior_grid_cam.distance = PRIOR_GRID_CAM_DISTANCE
prior_grid_cam.lookat[:] = PRIOR_GRID_CAM_LOOKAT

prior_grid_renderer = mujoco.Renderer(
    prior_grid_model, height=PRIOR_GRID_RENDER_HEIGHT, width=PRIOR_GRID_RENDER_WIDTH
)
prior_grid_frames = []
try:
    for t in range(_prior_num_steps_grid):
        for i in range(9):
            start = i * prior_nq_single
            prior_grid_data.qpos[start : start + prior_nq_single] = prior_qpos_with_offsets[i, t]
        mujoco.mj_forward(prior_grid_model, prior_grid_data)
        prior_grid_renderer.update_scene(prior_grid_data, camera=prior_grid_cam)
        prior_grid_frames.append(prior_grid_renderer.render().copy())
finally:
    prior_grid_renderer.close()

media.show_video(prior_grid_frames, fps=PRIOR_RENDER_FPS)


This browser does not support the video tag.


# Arena forage task-transfer: rollout + side-by-side render (self-contained)

Loads a checkpoint trained with `scamper.agent.task_transfer.arena_forage.train`
(step prefix `TaskTransfer`), rolls it out on the `ArenaForage` task, and
produces a side-by-side mp4: sim render on the left, 2D scent heatmap with the
growing rodent trajectory on the right. Mirrors the static plot in
`notebooks/analysis/arena_forage_collected_treats.ipynb` but animates the
trajectory so it stays in sync with the sim.

All state lives in `AF_*` / `af_*` variables and is independent of the RGM and
motion-prior sections above.


### Config


In [1]:
# ============ EDIT THESE ============
AF_CHECKPOINT_PATH = "/home/mila/a/aidan.sirbu/SCAMPER/scratch/arena_forage_checkpoints/scamper_forage"
AF_CHECKPOINT_STEP = None  # None = latest
AF_EPISODE_LENGTH = 2000
AF_SEED = 42

# Override env radii (None = keep the values baked into the checkpoint)
AF_MIN_SPAWN_RADIUS = 1.0
AF_SPAWN_RADIUS = 2.0

# Per-panel render settings (sim panel and heatmap panel use the same size)
AF_RENDER_HEIGHT = 480
AF_RENDER_WIDTH = 640
AF_RENDER_FPS = 50
AF_SIM_CAMERA_NAME = "close_profile-rodent"

# Output directory for the side-by-side mp4
AF_OUTPUT_DIR = "/home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/arena_forage_sidebyside"


### Loader helper

Defines `af_load_model(...)`, a self-contained port of the pattern in
`notebooks/analysis/arena_forage_collected_treats.ipynb`. Loads a task-transfer
checkpoint (`TaskTransfer` step prefix), reconstructs the base `ArenaForage`
env, attaches the correct wrapper for the training mode (`decoder_only`,
`prior_decoder`, or `scratch`), and returns jitted reset / step / inference
functions plus the loaded PPO brax params.


In [2]:
import os

os.environ.setdefault("XLA_PYTHON_CLIENT_PREALLOCATE", "false")
os.environ.setdefault("PYOPENGL_PLATFORM", "egl")
os.environ.setdefault("MUJOCO_GL", "egl")

import functools

import jax
import jax.numpy as jnp
import orbax.checkpoint as ocp
from brax.training.acme import running_statistics, specs
from brax.training.agents.ppo import networks as ppo_networks
from mujoco import mjx

from scamper.agent.distill_prior.distill_prior_networks import (
    create_abstract_distill_prior_policy,
)
from scamper.agent.task_transfer.arena_forage.checkpoint_utils import (
    load_task_transfer_metadata,
    load_task_transfer_brax_params,
    make_decoder_inference_fn,
    make_prior_inference_fn,
    make_rgm_inference_fn,
    _STEP_PREFIX as _AF_STEP_PREFIX,
)
from scamper.agent.task_transfer.arena_forage.wrappers import (
    DecoderHighLevelWrapper,
    FlatObsWrapper,
    PriorDecoderHighLevelWrapper,
    PriorRGMDecoderHighLevelWrapper,
    RGMDecoderHighLevelWrapper,
)
from scamper.agent.task_transfer.arena_forage.scratch_networks import (
    make_scratch_ppo_networks,
)
from scamper.environment.rodent import arena_forage as _arena_forage
from scamper.environment.rodent import consts as _af_rodent_consts


def _af_load_frozen_networks(checkpoint_path, step, mode, ckpt_cfg):
    """Load frozen networks directly from the task-transfer checkpoint.

    The task-transfer save logic writes a ``frozen_networks`` entry alongside
    the Brax params (see ``save_task_transfer_checkpoint``), so we don't need
    the original prior checkpoint at all. Only modes that use the RGM store
    ``rgm_params``; we match that here.
    """
    rgm_hidden_layer_sizes = tuple(
        ckpt_cfg["network_config"].get("rgm_layer_sizes", (1024, 1024))
    )
    abstract_normalizer, abstract_combined = create_abstract_distill_prior_policy(
        ckpt_cfg, rgm_hidden_layer_sizes
    )
    abstract_frozen = {
        "encoder_params": abstract_combined["params"]["encoder"],
        "prior_params": abstract_combined["params"]["prior"],
        "decoder_params": abstract_combined["params"]["decoder"],
        "imitation_normalizer": abstract_normalizer,
    }
    if mode in ("distill_prior", "distill_prior_no_rgm", "rgm_only"):
        abstract_frozen["rgm_params"] = abstract_combined["params"]["rgm"]

    mgr_options = ocp.CheckpointManagerOptions(
        create=False, step_prefix=_AF_STEP_PREFIX
    )
    with ocp.CheckpointManager(checkpoint_path, options=mgr_options) as mgr:
        data = mgr.restore(
            step,
            args=ocp.args.Composite(
                frozen_networks=ocp.args.StandardRestore(abstract_frozen),
            ),
        )
    return data["frozen_networks"]


def af_load_model(
    checkpoint_path,
    checkpoint_step=None,
    min_spawn_radius=None,
    spawn_radius=None,
):
    """Load a trained arena_forage task-transfer checkpoint.

    Returns (jit_reset, jit_step, jit_inference_fn, brax_params, env, config).
    Supports ``decoder_only``, ``scratch``, and ``prior_decoder`` modes.

    The task-transfer checkpoint is self-contained: frozen networks
    (encoder / prior / decoder / normalizer, plus rgm for some modes) are read
    directly from it — no separate prior-checkpoint lookup, so the absolute
    path baked into ``config["checkpoint"]["path"]`` is ignored.
    """
    ckpt_info = load_task_transfer_metadata(checkpoint_path, step=checkpoint_step)
    config = ckpt_info["config"]
    ckpt_step = ckpt_info["step"]
    mode = config["mode"]
    ckpt_cfg = config["checkpoint_config"]

    print(f"Loading checkpoint: {checkpoint_path}")
    print(f"  Mode: {mode}, Step: {ckpt_step}")

    frozen = _af_load_frozen_networks(checkpoint_path, ckpt_step, mode, ckpt_cfg)
    encoder_params = frozen["encoder_params"]
    prior_params = frozen["prior_params"]
    decoder_params = frozen["decoder_params"]
    normalizer_params = frozen["imitation_normalizer"]
    rgm_params = frozen.get("rgm_params")

    latent_size = ckpt_cfg["network_config"]["intention_size"]
    proprio_size = ckpt_cfg["network_config"]["obs_sizes"]["proprioception"]

    env_cfg = _arena_forage.default_config()
    xml_variant = config["env"].get("xml_variant", "full-collisions")
    xml_map = {
        "limited-collisions": _af_rodent_consts.RODENT_XML_PATH,
        "full-collisions": _af_rodent_consts.RODENT_FULL_COLLISION_XML,
        "no-tail-collisions": _af_rodent_consts.RODENT_NO_TAIL_COLLISION_XML,
    }
    env_cfg.walker_xml_path = xml_map[xml_variant]
    env_cfg.mujoco_impl = config["env"].get("mujoco_impl", "jax")
    env_cfg.ctrl_dt = ckpt_cfg["env_config"]["ctrl_dt"]
    env_cfg.num_treats = config["env"]["num_treats"]
    env_cfg.treat_sphere_radius = config["env"]["treat_sphere_radius"]
    env_cfg.treat_height = config["env"]["treat_height"]
    env_cfg.min_spawn_radius = (
        config["env"]["min_spawn_radius"]
        if min_spawn_radius is None
        else min_spawn_radius
    )
    env_cfg.spawn_radius = (
        config["env"]["spawn_radius"] if spawn_radius is None else spawn_radius
    )
    env_cfg.scent_sigma = config["env"]["scent_sigma"]
    if config["env"].get("reward_weights"):
        env_cfg.reward_terms = {
            "treat_collection": {
                "weight": config["env"]["reward_weights"]["treat_collection"]
            },
            "scent_proximity": {
                "weight": config["env"]["reward_weights"]["scent_proximity"]
            },
        }
    if mode == "scratch":
        env_cfg.torque_actuators = config.get("scratch", {}).get(
            "torque_actuators", True
        )
    else:
        env_cfg.torque_actuators = True

    decoder_fn = make_decoder_inference_fn(
        decoder_params, normalizer_params, ckpt_cfg
    )
    base_env = _arena_forage.ArenaForage(config=env_cfg)
    base_env._mjx_model = mjx.put_model(base_env._mj_model, impl=env_cfg.mujoco_impl)

    if mode == "decoder_only":
        env = DecoderHighLevelWrapper(
            base_env, decoder_fn, latent_size, proprio_size
        )
    elif mode == "scratch":
        env = FlatObsWrapper(base_env)
    elif mode == "distill_prior":
        prior_fn = make_prior_inference_fn(
            prior_params, normalizer_params, ckpt_cfg
        )
        rgm_fn = make_rgm_inference_fn(rgm_params, normalizer_params, ckpt_cfg)
        mcfg = config["distill_prior"]
        env = PriorRGMDecoderHighLevelWrapper(
            base_env,
            prior_fn,
            rgm_fn,
            decoder_fn,
            latent_size,
            proprio_size,
            gate_bias=mcfg["gate_bias"],
            gate_margin=mcfg.get("gate_margin", 0.0),
            rgm_noise=mcfg["rgm_noise"],
            rgm_logvar=mcfg.get("rgm_logvar", None),
        )
    elif mode == "rgm_only":
        rgm_fn = make_rgm_inference_fn(rgm_params, normalizer_params, ckpt_cfg)
        mcfg = config["rgm_only"]
        env = RGMDecoderHighLevelWrapper(
            base_env,
            rgm_fn,
            decoder_fn,
            latent_size,
            proprio_size,
            rgm_noise=mcfg["rgm_noise"],
            rgm_logvar=mcfg.get("rgm_logvar", None),
        )
    elif mode in ("prior_decoder", "distill", "distill_prior_no_rgm"):
        prior_fn = make_prior_inference_fn(
            prior_params, normalizer_params, ckpt_cfg
        )
        mcfg = config[mode]
        env = PriorDecoderHighLevelWrapper(
            base_env,
            prior_fn,
            decoder_fn,
            latent_size,
            proprio_size,
            deterministic_prior=mcfg["deterministic_prior"],
            noise_logvar=mcfg["noise_logvar"],
        )
    else:
        raise ValueError(f"Unknown mode: {mode}")

    jit_reset = jax.jit(env.reset)
    jit_step = jax.jit(env.step)

    start_state = jit_reset(jax.random.PRNGKey(0))
    obs_size = start_state.obs.shape[-1]
    policy_action_size = env.action_size
    normalize = running_statistics.normalize

    if mode == "scratch":
        def network_factory(*args, **kwargs):
            return make_scratch_ppo_networks(
                obs_size=obs_size,
                action_size=policy_action_size,
                policy_hidden_layer_sizes=tuple(config["network"]["policy_layers"]),
                value_hidden_layer_sizes=tuple(config["network"]["value_layers"]),
            )
        dummy_net = network_factory()
    else:
        network_factory = functools.partial(
            ppo_networks.make_ppo_networks,
            policy_hidden_layer_sizes=tuple(config["network"]["policy_layers"]),
            value_hidden_layer_sizes=tuple(config["network"]["value_layers"]),
        )
        dummy_net = network_factory(
            obs_size, policy_action_size, preprocess_observations_fn=normalize
        )

    key_p, key_v = jax.random.split(jax.random.PRNGKey(0))
    dummy_normalizer = running_statistics.init_state(
        specs.Array(start_state.obs.shape[-1:], jnp.dtype("float32"))
    )
    dummy_policy = dummy_net.policy_network.init(key_p)
    dummy_value = dummy_net.value_network.init(key_v)
    abstract_brax_params = (dummy_normalizer, dummy_policy, dummy_value)

    brax_params = load_task_transfer_brax_params(
        checkpoint_path, abstract_brax_params, step=ckpt_step
    )

    if mode == "scratch":
        ppo_network = network_factory()
    else:
        ppo_network = network_factory(
            obs_size, policy_action_size, preprocess_observations_fn=normalize
        )
    policy_network = ppo_network.policy_network
    parametric_action_distribution = ppo_network.parametric_action_distribution

    def inference_fn(params, observations, key_sample):
        del key_sample
        param_subset = (params[0], params[1])
        logits = policy_network.apply(*param_subset, observations)
        action = parametric_action_distribution.mode(logits)
        return action, {}

    jit_inference_fn = jax.jit(inference_fn)
    print("  Model loaded successfully.")
    return jit_reset, jit_step, jit_inference_fn, brax_params, env, config


E0424 17:41:37.821428   17733 numa_hwloc.cc:121] Call to hwloc_set_cpubind() failed: Invalid argument [22]
E0424 17:41:37.821462   17732 numa_hwloc.cc:121] Call to hwloc_set_cpubind() failed: Invalid argument [22]
E0424 17:41:37.821277   17731 numa_hwloc.cc:121] Call to hwloc_set_cpubind() failed: Invalid argument [22]


### Load the checkpoint and run a rollout

Populates `af_rollout` — a list of env `State`s spanning `AF_EPISODE_LENGTH + 1`
timesteps. Each `state.info["treat_positions"]` and `state.info["treat_collected"]`
are used by the visualization below.


In [3]:
import jax
from jax import random
import numpy as np

(
    af_jit_reset,
    af_jit_step,
    af_jit_inference_fn,
    af_brax_params,
    af_env,
    af_config,
) = af_load_model(
    AF_CHECKPOINT_PATH,
    checkpoint_step=AF_CHECKPOINT_STEP,
    min_spawn_radius=AF_MIN_SPAWN_RADIUS,
    spawn_radius=AF_SPAWN_RADIUS,
)

rng = random.PRNGKey(AF_SEED)
reset_rng, act_rng = random.split(rng)
state = af_jit_reset(reset_rng)
af_rollout = [state]
for _ in range(AF_EPISODE_LENGTH):
    _, act_rng = random.split(act_rng)
    action, _ = af_jit_inference_fn(af_brax_params, state.obs, act_rng)
    state = af_jit_step(state, action)
    af_rollout.append(state)

print(f"Rollout complete: {len(af_rollout)} frames")
print(
    f"Treats collected: "
    f"{int(np.sum(np.array(af_rollout[-1].info['treat_collected'])))}"
    f" / {int(np.array(af_rollout[0].info['treat_collected']).shape[0])}"
)


Loading checkpoint: /home/mila/a/aidan.sirbu/SCAMPER/scratch/arena_forage_checkpoints/scamper_forage
  Mode: distill_prior, Step: 22
Warp 1.11.0 initialized:
   CUDA Toolkit 12.9, Driver 13.0
   Devices:
     "cpu"      : "x86_64"
     "cuda:0"   : "NVIDIA A100-SXM4-80GB" (79 GiB, sm_80, mempool enabled)
   Kernel cache:
     /home/mila/a/aidan.sirbu/.cache/warp/1.11.0
Warp DeprecationWarning: The symbol `warp.types.warp_type_to_np_dtype` will soon be removed from the public API. It can still be accessed from `warp._src.types.warp_type_to_np_dtype` but might be changed or removed without notice.
Module mujoco.mjx.third_party.mujoco_warp._src.smooth e142b0f load on device 'cuda:0' took 15.21 ms  (cached)
Module mujoco.mjx.third_party.mujoco_warp._src.collision_driver de6dc98 load on device 'cuda:0' took 5.48 ms  (cached)
Module _nxn_broadphase__locals__kernel_8c837afb 8c837af load on device 'cuda:0' took 5.26 ms  (cached)
Module _primitive_narrowphase__locals__primitive_narrowphase_3a95

### Side-by-side render: sim + 2D trajectory heatmap

Runs the sim render (left panel) and builds a per-frame 2D heatmap with the
growing trajectory (right panel), then hconcats and saves to mp4. Mirrors the
static plot in `notebooks/analysis/arena_forage_collected_treats.ipynb` but
animates the trajectory so it stays in sync with the sim.


In [5]:
import imageio
import matplotlib.pyplot as plt
import numpy as np
from matplotlib.backends.backend_agg import FigureCanvasAgg
from matplotlib.collections import LineCollection
from matplotlib.colors import LinearSegmentedColormap
from pathlib import Path
from IPython.display import Video, display

# Unwrap to base arena_forage env for rendering + config access.
af_base_env = af_env
while hasattr(af_base_env, "env"):
    af_base_env = af_base_env.env
af_env_cfg = af_base_env._config
af_mode = af_config["mode"]

# Keep per-treat scent grids so we can recombine them each frame from the
# current `treat_collected` mask — collected treats drop out of both the
# heatmap and the scatter (matches `_log_scent_heatmap_video` in
# scamper/agent/task_transfer/arena_forage/logging.py).
_num_treats = af_env_cfg.num_treats
_sigma = af_env_cfg.scent_sigma
_extent = af_env_cfg.spawn_radius * 1.5
_grid_res = 60
_grid_1d = np.linspace(-_extent, _extent, _grid_res)
_gx, _gy = np.meshgrid(_grid_1d, _grid_1d)

_treat_pos = np.array(af_rollout[0].info["treat_positions"])
_scent_per_treat = np.zeros((_num_treats, _grid_res, _grid_res))
for t in range(_num_treats):
    _dist2 = (_gx - _treat_pos[t, 0]) ** 2 + (_gy - _treat_pos[t, 1]) ** 2
    _scent_per_treat[t] = np.exp(-_dist2 / (2 * _sigma**2))
_vmax = max(float(_scent_per_treat.sum(axis=0).max()), 1.0)

# Per-frame collected mask (cast once for fast indexing).
_treat_collected_per_frame = np.array(
    [np.array(s.info["treat_collected"]) for s in af_rollout]
)

# xy trajectory of the rodent.
_rodent_xy = np.array([np.array(s.data.qpos[:2]) for s in af_rollout])

# Truncated colormap for trajectory (skip the whitish low end).
_colors = plt.cm.YlOrRd(np.linspace(0.4, 1.0, 256))
_traj_cmap = LinearSegmentedColormap.from_list("YlOrRd_trunc", _colors)
_start_color = _traj_cmap(0.0)

# Render the sim with the viridis scent floor tiles enabled — same default the
# training eval rollout videos use (`render_scent=True` in
# `ArenaForage.render`).
print("Rendering sim frames...")
sim_frames = af_base_env.render(
    af_rollout,
    camera=AF_SIM_CAMERA_NAME,
    height=AF_RENDER_HEIGHT,
    width=AF_RENDER_WIDTH,
    render_scent=True,
)
sim_frames = [np.asarray(f) for f in sim_frames]
_num_frames = len(sim_frames)
print(f"  {_num_frames} sim frames at {sim_frames[0].shape}")

# Prepare a persistent matplotlib figure sized to match the sim panel.
_dpi = 100
_fig, _ax = plt.subplots(
    figsize=(AF_RENDER_WIDTH / _dpi, AF_RENDER_HEIGHT / _dpi), dpi=_dpi
)
_canvas = FigureCanvasAgg(_fig)
_im = _ax.imshow(
    _scent_per_treat.sum(axis=0),
    extent=[-_extent, _extent, -_extent, _extent],
    origin="lower",
    cmap="viridis",
    vmin=0,
    vmax=_vmax,
    aspect="equal",
)
_active_dots, = _ax.plot(
    _treat_pos[:, 0], _treat_pos[:, 1],
    "o", color="dodgerblue", markersize=6, linestyle="None",
)
_collected_dots, = _ax.plot(
    [], [], "x", color="gray", markersize=7, markeredgewidth=2, linestyle="None",
)
_lc = LineCollection(
    [], cmap=_traj_cmap, norm=plt.Normalize(0, _num_frames),
    linewidths=1.5, alpha=0.9,
)
_ax.add_collection(_lc)
_start_dot, = _ax.plot([_rodent_xy[0, 0]], [_rodent_xy[0, 1]], "o", color=_start_color, markersize=6)
_end_dot, = _ax.plot([], [], "s", color="red", markersize=6)
_ax.set_xlim(-_extent, _extent)
_ax.set_ylim(-_extent, _extent)
_ax.axis("off")
_fig.subplots_adjust(left=0, right=1, bottom=0, top=1)

print("Compositing side-by-side frames...")
combined_frames = []
for t in range(_num_frames):
    # Recombine scent from active treats only; recolor treat markers to
    # reflect collection state.
    collected = _treat_collected_per_frame[t]
    active = ~collected
    if active.any():
        _im.set_data(_scent_per_treat[active].sum(axis=0))
    else:
        _im.set_data(np.zeros_like(_gx))
    _active_dots.set_data(_treat_pos[active, 0], _treat_pos[active, 1])
    _collected_dots.set_data(_treat_pos[collected, 0], _treat_pos[collected, 1])

    pts = _rodent_xy[: t + 1].reshape(-1, 1, 2)
    if len(pts) >= 2:
        segs = np.concatenate([pts[:-1], pts[1:]], axis=1)
        _lc.set_segments(segs)
        _lc.set_array(np.arange(len(pts)))
    _end_dot.set_data([_rodent_xy[t, 0]], [_rodent_xy[t, 1]])

    _canvas.draw()
    hm = np.asarray(_canvas.buffer_rgba())[:, :, :3]
    h = min(sim_frames[t].shape[0], hm.shape[0])
    combined_frames.append(np.concatenate([sim_frames[t][:h], hm[:h]], axis=1))

plt.close(_fig)
print(f"  built {len(combined_frames)} combined frames at {combined_frames[0].shape}")

# Write mp4 and display inline.
out_dir = Path(AF_OUTPUT_DIR)
out_dir.mkdir(parents=True, exist_ok=True)
_run_id = Path(AF_CHECKPOINT_PATH).name
out_path = out_dir / f"arena_forage_sidebyside_{af_mode}_{_run_id}_seed{AF_SEED}.mp4"
with imageio.get_writer(str(out_path), fps=AF_RENDER_FPS) as writer:
    for f in combined_frames:
        writer.append_data(f)
print(f"Saved {out_path}")
display(Video(str(out_path), embed=True))

Rendering sim frames...
  2001 sim frames at (480, 640, 3)
Compositing side-by-side frames...
  built 2001 combined frames at (480, 1280, 3)
Saved /home/mila/a/aidan.sirbu/SCAMPER/notebooks/analysis/FinalNotebooks/Plots/arena_forage_sidebyside/arena_forage_sidebyside_distill_prior_scamper_forage_seed42.mp4
